In [1]:
import numpy as np
import matplotlib.pyplot as plt
import pandas as pd
import os
import ast

In [2]:
ast.literal_eval("[(4399, 4401), (4407, 4409), (4401.5, 4402.5), (4405.7, 4406.6)]")

[(4399, 4401), (4407, 4409), (4401.5, 4402.5), (4405.7, 4406.6)]

## Cutting the linelist to W = 80 mA in blue, and W = 60 in the red

In [2]:
# # Opening up the .txt file
# lines = np.genfromtxt('lines.txt', dtype=str)

# # Taking the columns that we're interested in
# line_list = []
# for t in lines:
#     species = t[0] + ' ' + t[1]
#     wave = t[2]
#     elow = t[3]
#     loggf = t[4]
#     ew = t[5]
    
#     line_dict = {'species': species, 'wave': wave, 'elow': elow, 'loggf': loggf, 'ew': ew}
#     line_list.append(line_dict)

# # Converting to a dataframe, then saving as a .csv
# line_df = pd.DataFrame(line_list)
# # line_df.to_csv('/data/misfit/benlowe/xshooter/linelist/lines.csv', index=False)

line_df = pd.read_csv('/data/misfit/benlowe/xshooter/linelist/lines.csv')


# Making cut on line list to include lines with EW >= 60mA
line_cut_df = line_df[((line_df['ew'] >= 80) & (line_df['wave'] >= 3300) & (line_df['wave'] <= 5560)) | ((line_df['ew'] >= 60) & (line_df['wave'] > 5600) & (line_df['wave'] <= 10200))]
line_cut_df
line_cut_df.to_csv('/data/misfit/benlowe/xshooter/linelist/lines_cut.csv', index=False)


## Extracting line list and windows for certain elements

In [2]:
def get_element(el):
    """Getting the line list and making the windows for the given element. Then saves 
    the line list and windows as .csv files.

    Parameters
    ----------
    el : str
        Element e.g. "Ca 1".

    Returns
    -------
    None
    """
    
    # Loading in the line list
    line_df = pd.read_csv('/data/misfit/benlowe/xshooter/linelist/lines_cut.csv')

    # Cutting the line list to only include the given element
    line_el_df = line_df[line_df['species'].str.contains(el)]
    
    # Making the windows
    window_size = 5 # ±A
    window_el_df = pd.DataFrame()

    species = line_el_df['species']
    waves = line_el_df['wave']

    window_el_df['species'] = species
    window_el_df['wavepeak'] = waves
    window_el_df['wavebase'] = waves - window_size
    window_el_df['wavetop'] = waves + window_size

    
    # Saving 
    el_species = el.split(" ")[0]
    if el.split(" ")[1] == "1":
        el_num = "I"
    if el.split(" ")[1] == "2":
        el_num = "II"

    # Making elemental directories
    el_mkdir = "/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/{0}_{1}/".format(el_species, el_num)
    os.makedirs(el_mkdir, exist_ok=True)
    
    el_linelist_path = el_mkdir + "lines_{0}_{1}.csv".format(el_species, el_num)
    line_el_df.to_csv(el_linelist_path, index=False)

    el_window_path = el_mkdir + "windows_{0}_{1}.csv".format(el_species, el_num)
    window_el_df.to_csv(el_window_path, index=False)
    
    return None


elements = ["Al 1", "Ba 2", "Ca 1", "Ca 2", "Co 1", "Cr 1", "Cr 2", "Cu 1", "Eu 2", "Fe 1", "Fe 2",
            "Mg 1", "Mn 1", "Mn 2", "Na 1", "Ni 1", "Sc 2", "Si 1", "Sr 2", "Ti 1", "Ti 2",
            "Y 2", "Zr 2"]

for el in elements:
    get_element(el)

## Masking-out regions

In [2]:
def mask(el_window_path, el_masks, el_name):
    """Appends the mask to the dataframe for each line in the window list.
    
    Parameters
    ----------
    el_window_path : str
        Path to the window list .csv file.
    el_masks : list
        List of dictionaries containing the line and mask for each line. 
        Structure: [{'line': 3570.254, 'mask': [(3570.254, 3570.256), (3570.258, 3570.260)]}, 
                    ...]
                    
    Returns
    -------
    el_df : DataFrame
        DataFrame containing the line list and the mask for each line.
    """
    
    # Loading in the window list
    el_windows = pd.read_csv(el_window_path + f"windows_{el_name}.csv")
    el_df = pd.DataFrame({'line': el_windows['wavepeak']})
    
    # windows_Al_I.csv
    
    # Appending the mask to the dataframe for each line
    for mask in el_masks:
        line = float(mask['line'])
        print(line)
        mask_list = mask['mask']
        
        el_df.loc[el_df['line'] == line, 'mask'] = str(mask_list)
        
        # Updating the wavebase and wavetop 
        # Saving original dataframe before overwriting
        el_windows.to_csv(el_window_path + f"windows_{el_name}_ALL.csv", index=False)
        
        # Updating the wavebase and wavetop in the current windows dataframe
        wavebase = float(mask['wavebase'])
        wavetop = float(mask['wavetop'])
        
        el_windows.loc[el_windows['wavepeak'] == line, 'wavebase'] = wavebase
        el_windows.loc[el_windows['wavepeak'] == line, 'wavetop'] = wavetop
        
    
    display(el_df)
    display(el_windows)    
    
    # Saving the dataframe to a .csv file
    el_df.to_csv(el_window_path + f"{el_name}_masksALL.csv", index=False)
    el_windows.to_csv(el_window_path + f"windows_{el_name}.csv", index=False)
    


### For Al-I

In [4]:
alI_masks = [{'line': 3961.52, 'wavebase': 3957.5, 'wavetop': 3962.5, 'mask': [(3957.6, 3959)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Al_I/', el_masks=alI_masks, el_name='Al_I')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

3961.52


,line,mask
0,3961.52,"[(3957.6, 3959)]"


,species,wavepeak,wavebase,wavetop
0,Al 1,3961.52,3957.5,3962.5


### For Ba-II

In [69]:
baII_masks = [{'line': 4554.032, 'wavebase': 4550.7, 'wavetop': 4559.6, 'mask': [(4552, 4553), (4555, 4557), (4558, 4559.4)]},
              {'line': 4934.077, 'wavebase': 4930, 'wavetop': 4937, 'mask': [(4930.5, 4931.5), (4932.3, 4933), (4935, 4936.6)]},
              {'line': 6496.897, 'wavebase': 6491.897, 'wavetop': 6501.897, 'mask': [(6498, 6500.5)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Ba_II/', el_masks=baII_masks, el_name='Ba_II')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

4554.032
4934.077
6496.897


,line,mask
0,4554.032,"[(4552, 4553), (4555, 4557), (4558, 4559.4)]"
1,4934.077,"[(4930.5, 4931.5), (4932.3, 4933), (4935, 4936..."
2,6496.897,"[(6498, 6500.5)]"


,species,wavepeak,wavebase,wavetop
0,Ba 2,4554.032,4550.700,4559.600
1,Ba 2,4934.077,4930.000,4937.000
2,Ba 2,6496.897,6491.897,6501.897


### For Ca-I

In [7]:
caI_masks = [{'line': 4226.728, 'wavebase': 4221.5, 'wavetop': 4232.2, 'mask': [(4221.7, 4223.5), (4229, 4230.5), (4230.6, 4232.0)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Ca_I/', el_masks=caI_masks, el_name='Ca_I')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

4226.728


,line,mask
0,4226.728,"[(4221.7, 4223.5), (4229, 4230.5), (4230.6, 42..."


,species,wavepeak,wavebase,wavetop
0,Ca 1,4226.728,4221.5,4232.2


### For Ca-II

In [4]:
caI_masks = [{'line': 8498.02, 'wavebase': 8491.02, 'wavetop': 8504.02, 'mask': [(8493, 8494.5), (8500.5, 8501.5), (8502, 8503.5)]},
             {'line': 8542.198, 'wavebase': 8535, 'wavetop': 8549, 'mask': [(8544, 8546)]},
             {'line': 8662.138, 'wavebase': 8655, 'wavetop': 8669, 'mask': [(8655.5, 8656.5), (8660.2, 8661), (8664, 8666)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Ca_II/', el_masks=caI_masks, el_name='Ca_II')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

8498.02
8542.198
8662.138


,line,mask
0,8498.020,"[(8493, 8494.5), (8500.5, 8501.5), (8502, 8503..."
1,8542.198,"[(8544, 8546)]"
2,8662.138,"[(8655.5, 8656.5), (8660.2, 8661), (8664, 8666)]"


,species,wavepeak,wavebase,wavetop
0,Ca 2,8498.020,8491.02,8504.02
1,Ca 2,8542.198,8535.00,8549.00
2,Ca 2,8662.138,8655.00,8669.00


### For Cr-I

In [5]:
crI_masks = [{'line': 5206.023, 'wavebase': 5201, 'wavetop': 5211.4, 'mask': [(5209.5, 5211)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Cr_I/', el_masks=crI_masks, el_name='Cr_I')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

5206.023


,line,mask
0,5206.023,"[(5209.5, 5211)]"


,species,wavepeak,wavebase,wavetop
0,Cr 1,5206.023,5201.0,5211.4


### For Co-I

In [ ]:
coI_masks = [{'line': 4121.318, 'wavebase': 4116.318, 'wavetop': 4126, 'mask': [(4119.4, 4120.5), (4122.2, 4123.5)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Co_I/', el_masks=coI_masks, el_name='Co_I')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

4121.318


,line,mask
0,4121.318,"[(4119.4, 4120.5), (4122.2, 4123.5)]"


,species,wavepeak,wavebase,wavetop
0,Co 1,4121.318,4116.318,4126.0


### For Eu-II

In [4]:
euII_masks = [{'line': 4129.725, 'wavebase': 4124.725, 'wavetop': 4135.725, 'mask': [(4126.5, 4128.5), (4131.3, 4133), (4134.2, 4135.2)]},
             {'line': 4205.042, 'wavebase': 4200.042, 'wavetop': 4210.042, 'mask': [(4201.4, 4202.8), (4206, 4207.3), (4208.4, 4209.5)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Eu_II/', el_masks=euII_masks, el_name='Eu_II')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

4129.725
4205.042


,line,mask
0,4129.725,"[(4126.5, 4128.5), (4131.3, 4133), (4134.2, 41..."
1,4205.042,"[(4201.4, 4202.8), (4206, 4207.3), (4208.4, 42..."


,species,wavepeak,wavebase,wavetop
0,Eu 2,4129.725,4124.725,4135.725
1,Eu 2,4205.042,4200.042,4210.042


### For Fe-I

In [ ]:
feI_masks = [{'line': 3570.254, 'mask': [(3567, 3569), (3573.2, 3575.8)]},
             {'line': 3745.899, 'mask': [(3741, 3742.2)]},
             {'line': 3820.425, 'mask': [(3817, 3819)]},
             {'line': 3859.911, 'mask': [(3862, 3864.5)]},
             {'line': 3895.656, 'mask': [(3893, 3894.3)]},
             {'line': 4045.812, 'mask': [(4040, 4042.5), (4043, 4045), (4047, 4049.8), (4050, 4051)]},
             {'line': 4271.760, 'mask': [(4267, 4269), (4273, 4276)]},
             {'line': 4307.901, 'mask': [(4302, 4304), (4305, 4307), (4310, 4313.2)]},
             {'line': 4383.544, 'mask': [(4377.544, 4379), (4380, 4382), (4384.5, 4386), (4387, 4388.5)]},
             {'line': 4404.750, 'mask': [(4399,4401), (4407, 4409), (4401.5, 4402.5), (4405.7, 4406.6)]}]
feI_df = mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/caffauFeI_windowsALL.csv', el_masks=feI_masks)

el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
feI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

,line,mask
0,3570.254,"[(3567, 3569), (3573.2, 3575.8)]"
1,3745.899,"[(3741, 3742.2)]"
2,3820.425,"[(3817, 3819)]"
3,3859.911,"[(3862, 3864.5)]"
4,3895.656,"[(3893, 3894.3)]"
5,4045.812,"[(4040, 4042.5), (4043, 4045), (4047, 4049.8),..."
6,4271.760,"[(4267, 4269), (4273, 4276)]"
7,4307.901,"[(4302, 4304), (4305, 4307), (4310, 4313.2)]"
8,4383.544,"[(4377.544, 4379), (4380, 4382), (4384.5, 4386..."
9,4404.750,"[(4399, 4401), (4407, 4409), (4401.5, 4402.5),..."


### For Mg-I

In [9]:
mgI_masks = [{'line': 5167.322, 'wavebase': 5162.5, 'wavetop': 5177.5, 'mask': [(5165.3, 5166.3), (5170.7, 5171.8)]},
             {'line': 5183.604, 'wavebase': 5179, 'wavetop': 5187.5, 'mask': [(5179.6, 5180.7), (5184.7, 5186)]},
             {'line': 8806.757, 'wavebase': 8801.757, 'wavetop': 8811.757, 'mask': [(8803, 8804.7), (8807.7, 8808.5), (8809.3, 8810)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Mg_I/', el_masks=mgI_masks, el_name='Mg_I')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

5167.322
5183.604
8806.757


,line,mask
0,5167.322,"[(5165.3, 5166.3), (5170.7, 5171.8)]"
1,5183.604,"[(5179.6, 5180.7), (5184.7, 5186)]"
2,8806.757,"[(8803, 8804.7), (8807.7, 8808.5), (8809.3, 88..."


,species,wavepeak,wavebase,wavetop
0,Mg 1,5167.322,5162.500,5177.500
1,Mg 1,5183.604,5179.000,5187.500
2,Mg 1,8806.757,8801.757,8811.757


### For Mn-I

In [12]:
mnI_masks = [{'line': 4033.06, 'wavebase': 4026, 'wavetop': 4038, 'mask': [(4027.8, 4029), (4031.8, 4032.4), (4035.3, 4036.7)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Mn_I/', el_masks=mnI_masks, el_name='Mn_I')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

4033.06


,line,mask
0,4033.06,"[(4027.8, 4029), (4031.8, 4032.4), (4035.3, 40..."


,species,wavepeak,wavebase,wavetop
0,Mn 1,4033.06,4026.0,4038.0


### For Ni-I

In [11]:
niI_masks = [{'line': 5476.904, 'wavebase': 5472.5, 'wavetop': 5481, 'mask': [(5478.8, 5480)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Ni_I/', el_masks=niI_masks, el_name='Ni_I')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

5476.904


,line,mask
0,3315.663,NaN
1,3320.259,NaN
2,3322.310,NaN
3,3361.554,NaN
4,3365.765,NaN
...,...,...
59,3783.530,NaN
60,3807.144,NaN
61,3831.691,NaN
62,3858.297,NaN


,species,wavepeak,wavebase,wavetop
0,Ni 1,3315.663,3310.663,3320.663
1,Ni 1,3320.259,3315.259,3325.259
2,Ni 1,3322.310,3317.310,3327.310
3,Ni 1,3361.554,3356.554,3366.554
4,Ni 1,3365.765,3360.765,3370.765
...,...,...,...,...
59,Ni 1,3783.530,3778.530,3788.530
60,Ni 1,3807.144,3802.144,3812.144
61,Ni 1,3831.691,3826.691,3836.691
62,Ni 1,3858.297,3853.297,3863.297


### For Si-I

In [ ]:
siI_masks = [{'line': 3905.523, 'wavebase': 3901.2, 'wavetop': 3909, 'mask': [(3906.3, 3907.3)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Si_I/', el_masks=siI_masks, el_name='Si_I')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

3905.523


,line,mask
0,3905.523,"[(3906.3, 3907.3)]"


,species,wavepeak,wavebase,wavetop
0,Si 1,3905.523,3901.2,3909.0


### For Sc-II

In [9]:
scII_masks = [{'line': 4246.822, 'wavebase': 4241.7, 'wavetop': 4252.5, 'mask': [(4242.5, 4244), (4249.5, 4252)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Sc_II/', el_masks=scII_masks, el_name='Sc_II')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

4246.822


,line,mask
0,4246.822,"[(4242.5, 4244), (4249.5, 4252)]"


,species,wavepeak,wavebase,wavetop
0,Sc 2,4246.822,4241.7,4252.5


### For Sr-II

In [3]:
srII_masks = [{'line': 4077.709, 'wavebase': 4072.709, 'wavetop': 4082.709, 'mask': [(4074, 4075.5), (4076, 4077), (4080, 4081)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Sr_II/', el_masks=srII_masks, el_name='Sr_II')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

4077.709


,line,mask
0,4077.709,"[(4074, 4075.5), (4076, 4077), (4080, 4081)]"


,species,wavepeak,wavebase,wavetop
0,Sr 2,4077.709,4072.709,4082.709


### For Ti-II

In [4]:
tiII_masks = [{'line': 3913.461, 'wavebase': 3908.5, 'wavetop': 3918, 'mask': [(3909.7, 3911), (3915.5, 3916.5)]},
              {'line': 4468.493, 'wavebase': 4463.3, 'wavetop': 4474, 'mask': [(4464, 4465), (4465.7, 4467.5), (4470.5, 4471.8)]},
              {'line': 4501.27, 'wavebase': 4495.5, 'wavetop': 4507, 'mask': [(4496.3, 4497.5), (4503.5, 4505)]}]
mask(el_window_path='/data/misfit/benlowe/xshooter/linelist/abund_lines/v3/Ti_II/', el_masks=tiII_masks, el_name='Ti_II')

# el_path = "/data/misfit/benlowe/xshooter/linelist/caffau_lines/Fe_I/"
# alI_df.to_csv(el_path + "caffauFeI_masksALL.csv", index=False)

3913.461
4468.493
4501.27


,line,mask
0,3913.461,"[(3909.7, 3911), (3915.5, 3916.5)]"
1,4468.493,"[(4464, 4465), (4465.7, 4467.5), (4470.5, 4471..."
2,4501.270,"[(4496.3, 4497.5), (4503.5, 4505)]"


,species,wavepeak,wavebase,wavetop
0,Ti 2,3913.461,3908.5,3918.0
1,Ti 2,4468.493,4463.3,4474.0
2,Ti 2,4501.270,4495.5,4507.0


Using linelist from Caffau et al. 2013

In [5]:
# Selecting all Fe I lines above 4000A
# feI_lines = ['4045.812', '4271.760', '4271.153', '4307.901', '4383.544', '4404.750']
feI_lines = ['3570.098', '3570.254', '3745.561', '3745.899', '3758.233', '3815.840', '3820.425', '38244.44',
             '3856.371', '3859.911', '3895.656', '3930.297', '4045.812', '4271.760', '4271.153', '4307.901', '4383.544', '4404.750']
feI_df = line_df[line_df['wave'].isin(feI_lines)]
feI_df
# Saving to .csv
# feI_df.to_csv('/data/misfit/benlowe/xshooter/linelist/caffauFeI_linesALL.csv', index=False)

,species,wave,elow,loggf,ew


Getting all Fe II lines

In [5]:
fe2_lines = line_df[line_df["species"] == 'Fe 2']
fe2_lines.to_csv('/data/misfit/benlowe/xshooter/linelist/lines_feII.csv', index=False)

Getting Ti II lines for tests

In [4]:
# Getting all Ti II lines
all_ti2_lines = line_df[line_df["species"] == 'Ti 2']

# Pre-selecting Ti II lines that will be used for our test
ti2_lines = [4468.493, 4571.971, 4399.765, 4394.059, 4330.698]
final_ti2_lines = all_ti2_lines[all_ti2_lines['wave'].isin(ti2_lines)]

final_ti2_lines.to_csv('/data/misfit/benlowe/xshooter/linelist/lines_TiII.csv')


# Defining the windows
window_size = 1 # ±A
window_df = pd.DataFrame()

species = final_ti2_lines['species']
waves = final_ti2_lines['wave']

window_df['species'] = species
window_df['wavepeak'] = waves
window_df['wavebase'] = waves - window_size
window_df['wavetop'] = waves + window_size

window_df.to_csv('/data/misfit/benlowe/xshooter/linelist/windows_TiII.csv')


## Opening up the extended VALD list that Thoams gave me

In [9]:
vald_linelist = np.genfromtxt('/data/misfit/benlowe/xshooter/linelist/vald_3300-9000_linelist_metal-poor.lin')
vald_linelist

ValueError: Some errors were detected !
    Line #2 (got 5 columns instead of 12)
    Line #3 (got 18 columns instead of 12)
    Line #4 (got 14 columns instead of 12)
    Line #5 (got 4 columns instead of 12)
    Line #6 (got 5 columns instead of 12)
    Line #7 (got 24 columns instead of 12)
    Line #8 (got 14 columns instead of 12)
    Line #9 (got 4 columns instead of 12)
    Line #10 (got 4 columns instead of 12)
    Line #11 (got 23 columns instead of 12)
    Line #12 (got 14 columns instead of 12)
    Line #13 (got 4 columns instead of 12)
    Line #14 (got 4 columns instead of 12)
    Line #15 (got 24 columns instead of 12)
    Line #16 (got 14 columns instead of 12)
    Line #17 (got 4 columns instead of 12)
    Line #18 (got 4 columns instead of 12)
    Line #19 (got 24 columns instead of 12)
    Line #20 (got 14 columns instead of 12)
    Line #21 (got 4 columns instead of 12)
    Line #22 (got 4 columns instead of 12)
    Line #23 (got 24 columns instead of 12)
    Line #2